# Dataset V3 Interactive Urban Heat Map

This notebook creates an interactive map of observed and model-predicted Land Surface Temperature for Chhatrapati Sambhajinagar.

The map uses final Dataset V3 hotspot outputs. It highlights high-priority hotspot zones and can be used in the Streamlit dashboard or opened directly in a browser.

In [1]:
import sys
!{sys.executable} -m pip install folium

c:\Study\SEM_5\ML\miniprojects\finalproject\urban-heat-stress-hotspot-detection\.venv\Scripts\python.exe: No module named pip


In [2]:
import folium
print("Folium installed successfully")

Folium installed successfully


In [3]:
import pandas as pd
import numpy as np
import folium
import os

# Load final point-level hotspot predictions
heatmap_data_v3 = pd.read_csv(
    "../data/processed/hotspot_predictions_v3.csv"
)

# Load final hotspot-priority zones
hotspot_zones_v3 = pd.read_csv(
    "../outputs/reports/hotspot_zone_priority_v3.csv"
)

print("Heat-map data loaded:", heatmap_data_v3.shape)
print("Hotspot zones loaded:", hotspot_zones_v3.shape)

display(heatmap_data_v3.head())

Heat-map data loaded: (9893, 21)
Hotspot zones loaded: (334, 13)


,NDVI,NDBI,Elevation,Population,LandCover_Bare_sparse_vegetation,LandCover_Built-up land,LandCover_Cropland,LandCover_Grassland,LandCover_Permanent_water_bodies,LandCover_Shrubland,...,LST,Latitude,Longitude,Predicted_LST,Residual,Heat_Category,LandCover_Class,Lat_Block,Lon_Block,Zone_ID
0,0.162286,0.127207,919,1.562392,0,0,1,0,0,0,...,43.919170,19.970832,75.438700,44.310135,-0.390964,High,Cropland,12,14,12_14
1,0.570751,-0.272423,488,1.361367,0,0,1,0,0,0,...,39.060455,19.729093,75.209548,39.418545,-0.358090,Low,Cropland,0,3,0_3
2,0.099371,0.055877,505,15.386780,0,0,0,1,0,0,...,40.231127,19.788775,75.225639,43.157870,-2.926744,Low,Grassland,3,4,3_4
3,0.196037,0.121404,757,2.643492,0,0,1,0,0,0,...,44.884761,19.960297,75.544582,45.710934,-0.826173,High,Cropland,11,20,11_20
4,0.165262,0.133151,586,31.397209,0,0,0,1,0,0,...,48.502735,19.867709,75.486062,46.815132,1.687603,Very High,Grassland,7,17,7_17


In [4]:
map_center = [
    heatmap_data_v3["Latitude"].mean(),
    heatmap_data_v3["Longitude"].mean()
]

heat_category_colors = {
    "Low": "green",
    "Moderate": "yellow",
    "High": "orange",
    "Very High": "red"
}

print("Map centre:", map_center)
print("Heat categories:", heatmap_data_v3["Heat_Category"].value_counts())

Map centre: [np.float64(19.89040940257608), np.float64(75.35708163785985)]
Heat categories: Heat_Category
High         2474
Low          2474
Moderate     2473
Very High    2472
Name: count, dtype: int64


In [5]:
urban_heat_map_v3 = folium.Map(
    location=map_center,
    zoom_start=11,
    tiles="CartoDB positron"
)

# Add observed LST points
for _, row in heatmap_data_v3.sample(n=min(4000, len(heatmap_data_v3)), random_state=42).iterrows():
    folium.CircleMarker(
        location=[row["Latitude"], row["Longitude"]],
        radius=3,
        color=heat_category_colors.get(
            row["Heat_Category"],
            "gray"
        ),
        fill=True,
        fill_opacity=0.65,
        popup=folium.Popup(
            f"""
            <b>Observed LST:</b> {row["LST"]:.2f} °C<br>
            <b>Predicted LST:</b> {row["Predicted_LST"]:.2f} °C<br>
            <b>Heat Category:</b> {row["Heat_Category"]}<br>
            <b>NDVI:</b> {row["NDVI"]:.3f}<br>
            <b>NDBI:</b> {row["NDBI"]:.3f}<br>
            <b>Population:</b> {row["Population"]:.2f}
            """,
            max_width=260
        )
    ).add_to(urban_heat_map_v3)

print("Observed LST points added to map.")

c:\Study\SEM_5\ML\miniprojects\finalproject\urban-heat-stress-hotspot-detection\.venv\Lib\site-packages\folium\raster_layers.py:130: UserWarning: CartoDB tiles now require an API key. Please provide one to continue using the tiles. You can request the key at https://carto.com/basemaps/apikey/.
  tiles = tiles.build_url(fill_subdomain=False, scale_factor="{r}")  # type: ignore


Observed LST points added to map.


In [6]:
priority_zones_v3 = hotspot_zones_v3[
    hotspot_zones_v3["Hotspot_Priority"] == "High Priority"
].copy()

for _, row in priority_zones_v3.iterrows():
    folium.Marker(
        location=[row["Zone_Latitude"], row["Zone_Longitude"]],
        popup=folium.Popup(
            f"""
            <b>High-Priority Hotspot Zone</b><br>
            <b>Zone ID:</b> {row["Zone_ID"]}<br>
            <b>Mean LST:</b> {row["Mean_LST"]:.2f} °C<br>
            <b>Maximum LST:</b> {row["Max_LST"]:.2f} °C<br>
            <b>Hotspot Percentage:</b> {row["Hotspot_Percentage"]:.2f}%<br>
            <b>Mean Population:</b> {row["Mean_Population"]:.2f}
            """,
            max_width=280
        ),
        icon=folium.Icon(
            icon="exclamation-sign",
            prefix="glyphicon"
        )
    ).add_to(urban_heat_map_v3)

print("High-priority hotspot zones added:", len(priority_zones_v3))

High-priority hotspot zones added: 10


In [7]:
legend_html = """
<div style="
position: fixed;
bottom: 30px;
left: 30px;
width: 180px;
z-index: 9999;
background-color: white;
border: 2px solid grey;
border-radius: 5px;
padding: 10px;
font-size: 13px;
">
<b>Observed Heat Category</b><br>
<span style="color:green;">●</span> Low<br>
<span style="color:yellow;">●</span> Moderate<br>
<span style="color:orange;">●</span> High<br>
<span style="color:red;">●</span> Very High<br>
<hr style="margin:6px 0;">
<span>⚠</span> High-priority hotspot zone
</div>
"""

urban_heat_map_v3.get_root().html.add_child(
    folium.Element(legend_html)
)

urban_heat_map_v3

In [8]:
os.makedirs("../outputs/maps", exist_ok=True)

map_output_path = "../outputs/maps/ahmedabad_urban_heat_map_v3.html"

urban_heat_map_v3.save(map_output_path)

print("Interactive heat map saved:")
print(map_output_path)

Interactive heat map saved:
../outputs/maps/sambhajinagar_urban_heat_map_v3.html


## Dataset V3 Interactive Heat Map Conclusion

The interactive map visualizes observed and model-predicted Land Surface Temperature across sampled locations in Chhatrapati Sambhajinagar.

Point colours represent observed heat-stress categories, while markers identify the top 10 high-priority hotspot zones.

The map is generated from Dataset V3 hotspot outputs and can be opened in a browser or embedded in the Streamlit dashboard.